# EDA Données VLille

In [1]:
import pandas as pd
from datetime import datetime
import numpy as np
import plotly.express as px

## Import base et nettoyages supplémentaires

In [2]:
df = pd.read_parquet("data_vlille_2025.parquet")

In [ ]:
def clean_date(df, date_column):
    mask = np.where(df[date_column].str.startswith("2025"), True, False)
    df.loc[mask, date_column] = df.loc[mask, date_column].apply(
        lambda x: f"{x[-2:]}-{x[5:7]}-2025"
    )
    df[date_column] = pd.to_datetime(df[date_column], format="%d-%m-%Y")
    return df


column_good_nomen_list = [
    "ID_station",
    "geometry_coordinates",
    "station_nom",
    "station_adresse",
    "station_commune",
    "station_etat",
    "station_nb_places_dispo",
    "station_nb_velos_dispo",
    "station_etat_connexion",
    "station_x",
    "station_y",
    "station_date_modification",
    "Date_Scrapping",
    "Heure_Min_Scrapping",
    "date_modification_utc_paris",
    "is_modified",
]

df.columns = column_good_nomen_list

to_drop = ["geometry_coordinates", "is_modified"]

df = df.drop(columns=to_drop)

In [ ]:
# df["ID_station"] = df["ID_station"].str.replace("vlille_temps_reel.", "", regex=False)
df["date_modification_utc_paris"] = pd.to_datetime(
    df["station_date_modification"]
).dt.tz_convert("Europe/Paris")
df = clean_date(df, "Date_Scrapping")

In [5]:
print(df.info())
df.head()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 6638067 entries, 0 to 6638066
Data columns (total 14 columns):
 #   Column                       Dtype                       
---  ------                       -----                       
 0   ID_station                   object                      
 1   station_nom                  object                      
 2   station_adresse              object                      
 3   station_commune              object                      
 4   station_etat                 object                      
 5   station_nb_places_dispo      Int64                       
 6   station_nb_velos_dispo       Int64                       
 7   station_etat_connexion       object                      
 8   station_x                    float64                     
 9   station_y                    float64                     
 10  station_date_modification    object                      
 11  Date_Scrapping               datetime64[ns]              
 12  

,ID_station,station_nom,station_adresse,station_commune,station_etat,station_nb_places_dispo,station_nb_velos_dispo,station_etat_connexion,station_x,station_y,station_date_modification,Date_Scrapping,Heure_Min_Scrapping,date_modification_utc_paris
0,308,SADI CARNOT,178 rue Sadi Carnot,Haubourdin,EN SERVICE,0,20,CONNECTÉ,2.994654,50.611307,2025-03-14T09:25:17.446+00:00,2025-03-14,08:26,2025-03-14 10:25:17.446000+01:00
1,308,SADI CARNOT,178 rue Sadi Carnot,Haubourdin,EN SERVICE,0,20,CONNECTÉ,2.994654,50.611307,2025-11-05T08:45:11.429+00:00,2025-11-05,07:45,2025-11-05 09:45:11.429000+01:00
2,308,SADI CARNOT,178 rue Sadi Carnot,Haubourdin,EN SERVICE,0,20,CONNECTÉ,2.994654,50.611307,2025-03-14T09:41:18.075+00:00,2025-03-14,08:42,2025-03-14 10:41:18.075000+01:00
3,308,SADI CARNOT,178 rue Sadi Carnot,Haubourdin,EN SERVICE,0,20,CONNECTÉ,2.994654,50.611307,2025-03-14T11:16:16.070+00:00,2025-03-14,10:16,2025-03-14 12:16:16.070000+01:00
4,308,SADI CARNOT,178 rue Sadi Carnot,Haubourdin,EN SERVICE,0,20,CONNECTÉ,2.994654,50.611307,2025-03-14T22:15:19.907+00:00,2025-03-14,21:15,2025-03-14 23:15:19.907000+01:00


## Début EDA

### Identification de bases stations qui ne fonctionnent pas + de stations redondantes. 

On s'intéresse à l'utilisation moyenne des stations pour dresser des premières statistiques descriptives mais surtout pour identifier si certaines stations ne posent pas problème dans notre jeu de donnée.

In [ ]:
mean_par_station_df = df.groupby(["ID_station", "station_nom"])[
    ["station_nb_velos_dispo", "station_nb_places_dispo"]
].mean()
mean_par_station_df["capacite_station"] = (
    mean_par_station_df["station_nb_velos_dispo"]
    + mean_par_station_df["station_nb_places_dispo"]
)

mean_par_station_df.describe()


,station_nb_velos_dispo,station_nb_places_dispo,capacite_station
count,303.0,303.0,303.0
mean,6.496894,11.183693,17.680587
std,3.52859,5.844453,8.323221
min,0.0,0.0,0.0
25%,4.669981,7.999057,13.967095
50%,6.734423,10.695592,17.984827
75%,8.825799,14.039201,20.490505
max,16.051266,29.056473,39.978632


Ici on observe la présence de station avec 0 vélos disponibles en moyenne et 0 places disponibles en moyenne. On constate même que certaines stations ont une capacité moyenne de 0.
Certaines stations ont donc un comportement anormal et sont probablement à retirer pour notre analyse. 

Pour investiguer on vient analyser les stations qui ont un nombre de vélo disponible inférieur à 3 en moyenne ou un nombre de places disponibles inférieur à 3 en moyenne. On peut également détecter des petites stations qui ne sont pas forcément anormales. Ou des stations qui seraient très fréquentées et qui seraient vides ou pleines très souvent.

In [ ]:
anomalies_station = mean_par_station_df[
    (mean_par_station_df["station_nb_velos_dispo"] <= 3)
    | (mean_par_station_df["station_nb_places_dispo"] <= 3)
]
print("Nombres de stations détectées :", anomalies_station.shape[0])
display(anomalies_station)
anomalies_station.describe()

Nombres de stations détectées : 49


,,station_nb_velos_dispo,station_nb_places_dispo,capacite_station
ID_station,station_nom,,,
1,METROPOLE EUROPEENNE DE LILLE,0.0,0.0,0.0
105,VERDUN,0.0,0.0,0.0
106,CONCORDE,0.0,0.0,0.0
109,SQUARE DU PORTUGAL,0.0,0.0,0.0
112,SQUARE CHARLES DE GAULLE,0.0,0.0,0.0
118,COLLEGE LAVOISIER,0.0,0.0,0.0
126,LE POLYEDRE,0.0,3.0,3.0
127,FLERS MAIRIE,0.0,0.0,0.0
128,RUE LOUISE MICHEL,0.0,1.0,1.0


,station_nb_velos_dispo,station_nb_places_dispo,capacite_station
count,49.0,49.0,49.0
mean,0.551138,5.895312,6.44645
std,1.046598,7.244727,7.478174
min,0.0,0.0,0.0
25%,0.0,0.0,0.0
50%,0.0,2.217409,3.0
75%,0.385454,12.0,12.0
max,3.782322,24.0,24.0


On répère des stations "fantômes" qui n'ont aucune capacité. Ces stations seront supprimées du jeu de données car considérées comme non fonctionnelles.

On repère aussi des stations avec un nombre de vélos disponibles constament égal à 0. Ces stations vont être considérées comme non fonctionnelles car elles n'ont jamais eu un seul vélo disponible donc n'ont jamais pu être utilisées.

Reste à étudier plus précisément les stations qui restent. 

In [8]:
mask = anomalies_station.station_nb_velos_dispo <= 0
anomalies_station_to_del_df = anomalies_station.loc[mask]
anomalies_station_to_treat_df = anomalies_station.loc[~mask]
anomalies_station_to_treat_df

,,station_nb_velos_dispo,station_nb_places_dispo,capacite_station
ID_station,station_nom,,,
181,MARIE MARRANT,0.385454,15.510368,15.895822
187,CITÉ MARIANNE,1.501269,10.482067,11.983337
203,VICTOR PROVO,2.866807,13.132699,15.999506
210,LINNE,3.782322,2.217409,5.999731
234,ALSACE,2.906312,12.987161,15.893473
237,RUE DES ANGES,1.275633,3.170318,4.445951
240,POSTE,2.063027,3.936928,5.999955
245,JARDIN BOTANIQUE,2.815945,5.184055,8.0
246,CAVELL,1.767059,4.223335,5.990393


In [ ]:
anomalies_station_to_del_list = list(
    anomalies_station_to_del_df.index.get_level_values(1)
)
anomalies_station_to_treat_list = list(
    anomalies_station_to_treat_df.index.get_level_values(1)
)
anomalies_station_to_treat_list

['MARIE MARRANT',
 'CITÉ MARIANNE',
 'VICTOR PROVO',
 'LINNE',
 'ALSACE',
 'RUE DES ANGES',
 'POSTE',
 'JARDIN BOTANIQUE',
 'CAVELL',
 'RUE SAINT BLAISE',
 'BLANCHEMAILLE',
 'TEST CYKLEO LILLE',
 'MITTERIE',
 'PLACE PHILIPPE LEBON',
 'STATION TEST']

In [ ]:
def plot_distrib_station(df, list_station_to_inspect):
    df = df[df.station_nom.isin(list_station_to_inspect)]
    df["date_modification_utc_paris"] = pd.to_datetime(
        df["date_modification_utc_paris"]
    )
    df = df.sort_values("date_modification_utc_paris")
    fig = px.line(
        df,
        x="date_modification_utc_paris",
        y="station_nb_velos_dispo",
        color="station_nom",
        title="Nombre de vélos disponibles par arrêt sur l'année",
    )
    return fig.show()


plot_distrib_station(df, anomalies_station_to_treat_list)

C:\Users\coulo\AppData\Local\Temp\ipykernel_32720\3685849841.py:3: SettingWithCopyWarning:


A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy



Après analyse, on observable que la plupart des stations qui nous restent sont bien des stations actives.Le faible nombre de vélos disponibles moyens et souvent lié à des mois où la borne n'a pas transmise d'infos. Probablement en raison de travaux dans les rues comme pour la place Philippe Lebon. 
Nous identifions néanmoins "TEST CYCKLEO LILLE", "STATION TEST" comme des stations à retirer.
Pour automatiser le retrait on utilise un critère qui vise à retirer les stations qui ont un nombre de vélo inférieur à 0.02 nombre de vélos disponibles à l'année.  

On utilise ce type de retrait car certaines stations retirées aujourd'hui pourrait en réalité s'avérer actives à une date future en raison de travaux terminées ou de réparations. 

In [ ]:
to_append = (
    anomalies_station_to_treat_df[
        anomalies_station_to_treat_df.station_nb_velos_dispo < 0.02
    ]
    .index.get_level_values(1)
    .tolist()
)
anomalies_station_to_del_list = anomalies_station_to_del_list + to_append
len(anomalies_station_to_del_list)

36

Retrait des stations identifiées comme non fonctionnelles du jeu de données.

In [12]:
print("Nombre de stations avant retrait des anomalies :", df["station_nom"].nunique())
df = df[~df.station_nom.isin(anomalies_station_to_del_list)]
print("Nouveau nombre de stations :", df["station_nom"].nunique())
print("Stations retirées :", len(anomalies_station_to_del_list))

Nombre de stations avant retrait des anomalies : 302
Nouveau nombre de stations : 266
Stations retirées : 36


In [ ]:
import plotly.express as px
from datetime import date

df = df.sort_values("date_modification_utc_paris")
df = df[df["Date_Scrapping"] >= pd.Timestamp("2025-01-01")]
to_plot = (
    df.groupby(df["date_modification_utc_paris"].dt.floor("h"))[
        "station_nb_places_dispo"
    ]
    .mean()
    .round()
)
px.line(
    to_plot,
    x=to_plot.index,
    y="station_nb_places_dispo",
    title="Moyenne du nombre de places disponibles au fil du temps",
)
# date_ref = pd.Timestamp("2025-11-14", tz="Europe/Paris")
# df_angellier = df[df["station_nom"] == "ANGELLIER"]
# df_angellier = df_angellier[df_angellier["date_modification_utc_paris"] >= date_ref]
# df_angellier = df_angellier.sort_values("date_modification_utc_paris")
# px.line(df_angellier, x=df_angellier.date_modification_utc_paris, y="station_nb_places_dispo", title="Moyenne du nombre de places disponibles au fil du temps")

In [18]:
df.columns

Index(['ID_station', 'station_nom', 'station_adresse', 'station_commune',
       'station_etat', 'station_nb_places_dispo', 'station_nb_velos_dispo',
       'station_etat_connexion', 'station_x', 'station_y',
       'station_date_modification', 'Date_Scrapping', 'Heure_Min_Scrapping',
       'date_modification_utc_paris'],
      dtype='object')

In [ ]:
mean_par_station_df = df.groupby(["ID_station", "station_nom"]).agg(
    {"station_nb_velos_dispo": "mean", "station_nb_places_dispo": "mean"}
)
mean_par_station_df["capacite_station"] = (
    mean_par_station_df["station_nb_velos_dispo"]
    + mean_par_station_df["station_nb_places_dispo"]
)
etat_connexion_counts = (
    df.groupby(["ID_station", "station_nom"])["station_etat_connexion"]
    .value_counts(normalize=True)
    .reset_index()
)
etat_connexion_counts.proportion = etat_connexion_counts.proportion * 100

display(etat_connexion_counts)
mean_par_station_df.describe()


,ID_station,station_nom,station_etat_connexion,proportion
0,10,RIHOUR,CONNECTÉ,99.546597
1,10,RIHOUR,DÉCONNECTÉ,0.453403
2,100,SAINT MAUR,CONNECTÉ,99.331119
3,100,SAINT MAUR,DÉCONNECTÉ,0.668881
4,101,MONS SARTS,CONNECTÉ,99.156042
...,...,...,...,...
527,98,PLACE DU MARCHE,DÉCONNECTÉ,0.884360
528,99,LA MADELEINE MAIRIE,CONNECTÉ,99.564554
529,99,LA MADELEINE MAIRIE,DÉCONNECTÉ,0.435446
530,995,STATION PROVISOIRE 1,CONNECTÉ,99.143811


,station_nb_velos_dispo,station_nb_places_dispo,capacite_station
count,266.0,266.0,266.0
mean,7.392769,12.048587,19.441355
std,2.752518,4.996018,6.753957
min,0.385454,2.217409,4.445951
25%,5.508541,9.026396,15.92906
50%,7.347751,10.891558,17.997598
75%,9.105888,14.268383,23.429633
max,16.051266,29.056473,39.978632


Nos statistiques descriptives souffrent actuellement d'un éceuil car les périodes d'inactivités des stations est actuellement considérées de la même manière qu'en période d'activité. 
Dans le cas du traitement des stations qui ont pu être été inactives, on devrait traiter comme NaN les valeurs de vélos disponibles et places disponibles pour les périodes où la station était inactive.

Par exemple, 12 stations ont été déconnectés plus de 25% du temps entre Janvier et Octobre dont 2 plus de 90% du temps. 

In [104]:
px.bar(
    etat_connexion_counts,
    x=etat_connexion_counts.station_nom,
    y=etat_connexion_counts.proportion,
    color=etat_connexion_counts.station_etat_connexion,
)
etat_connexion_counts_deco = etat_connexion_counts[
    etat_connexion_counts.station_etat_connexion == "DÉCONNECTÉ"
]
etat_connexion_counts_deco_count = etat_connexion_counts_deco.proportion.round().value_counts().reset_index()
etat_connexion_counts_deco_count
fig = px.bar(
    etat_connexion_counts_deco_count,
    x= etat_connexion_counts_deco_count["proportion"],
    y = etat_connexion_counts_deco_count["count"],
    # size =(etat_connexion_counts_deco_count["count"]*2),
    title="Répartition de stations en fonction de leurs disponibilités, taille proportionnelle à la racine du nombre de stations",
    text_auto=True,
)
# fig.update_yaxes(dtick=10)
fig.update_xaxes(dtick=10)  
fig.show()